# Stoichiometry EXCESS_COUPLED Test

Model-specific suite for `StoichiometryMode.EXCESS_COUPLED` with `Kinetics.EXCESS`.

This notebook validates EXCESS coupling and presents q-rates and stoichiometric yields over a glucose sweep.

In [13]:
import sys
from pathlib import Path
import numpy as np
import pandas as pd

repo_root = Path.cwd().parent
src_path = repo_root / "src"
if str(src_path) not in sys.path:
    sys.path.insert(0, str(src_path))

from animakinetica.core.parameters import SimulationParameters
from animakinetica.core.simulation import CellCultureSimulation
from animakinetica.models.kinetics import Kinetics
from animakinetica.models.odesystems import OperatingMode
from animakinetica.analysis.kinetic_visualization import (
    plot_simulated_NFs,
    plot_simulated_IFs,
    plot_kinetic_rates,
    plot_kinetics,
    )
from animakinetica.analysis.stoichiometric_visualization import plot_stoichiometric_yields

print("Imports OK")

Imports OK


In [14]:
params = SimulationParameters.load_parameters([
    "base_parameters",
    "excess_kinetics/excess_kinetics_continuous",
    "stoichiometry/anab_GFI",
    "cell_properties/cell_GFI",
    "operating_modes/batch_excess", # Modified initial concentrations
])

sim = CellCultureSimulation(
    parameters=params,
    kinetics=Kinetics.EXCESS,
    operating_mode=OperatingMode.BATCH,
    performance_mode=False,
    solver_method="LSODA",
)

sim.run_simulation(number_of_batches=1)
batch = sim.data.batches[0]

assert sim.stoichiometry_mode.name == "EXCESS_COUPLED"
print("Batch simulation completed with EXCESS_COUPLED stoichiometry")

Loading parameters from 5 file(s) sequentially...
  [1/5] Base: c:\Users\btumulero\OneDrive - Delft University of Technology\Documents\01. Code\animakinetica\config\parameter_sets\base_parameters.yaml
  [2/5] Updating with: c:\Users\btumulero\OneDrive - Delft University of Technology\Documents\01. Code\animakinetica\config\parameter_sets\excess_kinetics\excess_kinetics_continuous.yaml
  [3/5] Updating with: c:\Users\btumulero\OneDrive - Delft University of Technology\Documents\01. Code\animakinetica\config\parameter_sets\stoichiometry\anab_GFI.yaml
  [4/5] Updating with: c:\Users\btumulero\OneDrive - Delft University of Technology\Documents\01. Code\animakinetica\config\parameter_sets\cell_properties\cell_GFI.yaml
  [5/5] Updating with: c:\Users\btumulero\OneDrive - Delft University of Technology\Documents\01. Code\animakinetica\config\parameter_sets\operating_modes\batch_excess.yaml
Successfully loaded parameters from 5 file(s).
run_simulation execution time: 13.836 ms
Batch simulatio

In [15]:
import plotly.graph_objects as go

# Graphing settup
# Sweep A: C_Glc in at fixed C_Gln = 1 mmol/L or in meshgrid
C_Glc_sweep = np.linspace(0.0, 25.0, 301)
C_Gln_fixed = 1.0

# Sweep B: C_Gln in at fixed C_Glc = 1 mmol/L or in meshgrid
C_Gln_sweep = np.linspace(0.0, 10.0, 301)
C_Glc_fixed = 1.0

# For catabolic yield calculations, we need growth rate as well
mu_sweep = np.linspace(0.0, 0.5, 301)  # example growth rate sweep from 0 to 1 1/h
mu_fixed = 0.025

# Reuse the excess model implementation directly
excess_model = sim.kinetic_model 

# ---- 1D sweeps requested by user ----

# Evaluate all four excess terms for each sweep
# return order:
# [delta_q_Glc_Glc, delta_q_Gln_Glc, delta_q_Glc_Gln, delta_q_Gln_Gln]
excess_vs_glc = np.array([
    excess_model.delta_q_excess_Glc_Gln(C_Glc, C_Gln_fixed)
    for C_Glc in C_Glc_sweep
], dtype=float)

excess_vs_gln = np.array([
    excess_model.delta_q_excess_Glc_Gln(C_Glc_fixed, C_Gln)
    for C_Gln in C_Gln_sweep
], dtype=float)

# New interface: inspect catabolic terms via get_cat_yield_terms
cat_terms_vs_glc = [
    excess_model.get_cat_yield_terms(mu=mu_fixed, C_Glc=C_Glc, C_Gln=C_Gln_fixed)
    for C_Glc in C_Glc_sweep
]
q_Lac_lim_vs_glc = np.array([d["q_Lac_lim"] for d in cat_terms_vs_glc], dtype=float)
q_Lac_exc_vs_glc = np.array([d["q_Lac_exc"] for d in cat_terms_vs_glc], dtype=float)
q_Lac_cat_vs_glc = np.array([d["q_Lac_cat"] for d in cat_terms_vs_glc], dtype=float)

labels = [
    "delta_q_Glc_Glc",
    "delta_q_Gln_Glc",
    "delta_q_Glc_Gln",
    "delta_q_Gln_Gln",
]

fig_glc = go.Figure()
for i, name in enumerate(labels):
    fig_glc.add_trace(
        go.Scatter(
            x=C_Glc_sweep,
            y=excess_vs_glc[:, i] * 1e9,  # convert to mmol / 10e9 cells / h for better readability
            mode="lines",
            name=name,
        )
    )
fig_glc.update_layout(
    title="Excess contributions vs glucose (C_Gln = 1 mmol/L)",
    xaxis_title="Glucose concentration, C_Glc (mmol/L)",
    yaxis_title="Excess term (mmol / 10e9 cells / h)",
    template="plotly_white",
)
fig_glc.show()

fig_gln = go.Figure()
for i, name in enumerate(labels):
    fig_gln.add_trace(
        go.Scatter(
            x=C_Gln_sweep,
            y=excess_vs_gln[:, i] * 1e9,
            mode="lines",
            name=name,
        )
    )
fig_gln.update_layout(
    title="Excess contributions vs glutamine (C_Glc = 1 mmol/L)",
    xaxis_title="Glutamine concentration, C_Gln (mmol/L)",
    yaxis_title="Excess term (mmol / 10e9 cells / h)",
    template="plotly_white",
)
fig_gln.show()

fig_q_Lactate_empirical = go.Figure()
fig_q_Lactate_empirical.add_trace(
    go.Scatter(
        x=C_Glc_sweep,
        y=q_Lac_lim_vs_glc * 1e9,
        mode="lines",
        name="q_Lac_lim",
    )
)
fig_q_Lactate_empirical.add_trace(
    go.Scatter(
        x=C_Glc_sweep,
        y=q_Lac_exc_vs_glc * 1e9,
        mode="lines",
        name="q_Lac_exc",
    )
)
fig_q_Lactate_empirical.add_trace(
    go.Scatter(
        x=C_Glc_sweep,
        y=q_Lac_cat_vs_glc * 1e9,
        mode="lines",
        name="q_Lac_cat_total",
    )
)
fig_q_Lactate_empirical.update_layout(
    title=f"Empirical excess kinetics of (catabolic) lactate production vs glucose (mu = {mu_fixed} 1/h)",
    xaxis_title="Glucose concentration, C_Glc (mmol/L)",
    yaxis_title="q_Lac_cat (mmol / 10e9 cells / h)",
    template="plotly_white",
)
fig_q_Lactate_empirical.show()


# ---- 3D surfaces over same ranges ----
X_glc, Y_gln = np.meshgrid(C_Glc_sweep, C_Gln_sweep)

Z_delta_q_Glc = np.zeros_like(X_glc, dtype=float)
Z_delta_q_Gln = np.zeros_like(X_glc, dtype=float)
Z_delta_Y_cat_Lac_Glc = np.zeros_like(X_glc, dtype=float)
Z_delta_Y_cat_Gln_Glc = np.zeros_like(X_glc, dtype=float)


for r in range(X_glc.shape[0]):
    for c in range(X_glc.shape[1]):
        dvals = excess_model.delta_q_excess_Glc_Gln(X_glc[r, c], Y_gln[r, c])
        Z_delta_q_Glc[r, c] = (dvals[0] + dvals[1]) * 1e9  # sum of Glc contributions
        Z_delta_q_Gln[r, c] = (dvals[2] + dvals[3]) * 1e9  # sum of Gln contributions
        yield_vals = excess_model.calculate_cat_yields_from_excess(mu_fixed, X_glc[r, c], Y_gln[r, c])  # example mu=0.5 1/h for yield back-calculation
        Z_delta_Y_cat_Lac_Glc[r, c] = yield_vals[0]  # Catabolic yield of lactate on glucose
        Z_delta_Y_cat_Gln_Glc[r, c] = yield_vals[1] # Catabolic yield of glutamine on glucose#  

fig_3d_glc_glc = go.Figure(
    data=[
        go.Surface(
            x=X_glc,
            y=Y_gln,
            z=Z_delta_q_Glc,
            colorscale="Viridis",
            colorbar=dict(title="delta_q_Glc_excess"),
        )
    ]
)
fig_3d_glc_glc.update_layout(
    title="3D surface: delta_q_Glc_excess",
    scene=dict(
        xaxis_title="C_Glc (mmol/L)",
        yaxis_title="C_Gln (mmol/L)",
        zaxis_title="delta_q_Glc_excess (mmol / 10e9 cells / h)",
    ),
)
fig_3d_glc_glc.show()

fig_3d_gln_gln = go.Figure(
    data=[
        go.Surface(
            x=X_glc,
            y=Y_gln,
            z=Z_delta_q_Gln,
            colorscale="Plasma",
            colorbar=dict(title="delta_q_Gln_excess"),
        )
    ]
)
fig_3d_gln_gln.update_layout(
    title="3D surface: delta_q_Gln_excess",
    scene=dict(
        xaxis_title="C_Glc (mmol/L)",
        yaxis_title="C_Gln (mmol/L)",
        zaxis_title="delta_q_Gln_excess (mmol / 10e9 cells / h)",
    ),
)
fig_3d_gln_gln.show()

fig_3d_Y_lac_glc = go.Figure(
    data=[
        go.Surface(
            x=X_glc,
            y=Y_gln,
            z=Z_delta_Y_cat_Lac_Glc,
            colorscale="Plasma",
            colorbar=dict(title="delta_Y_cat_Lac_Glc"),
        )
    ]
)
fig_3d_Y_lac_glc.update_layout(
    title=f"3D surface: delta_Y_cat_Lac_Glc at constant mu= {mu_fixed} 1/h",
    scene=dict(
        xaxis_title="C_Glc (mmol/L)",
        yaxis_title="C_Gln (mmol/L)",
        zaxis_title="delta_Y_cat_Lac_Glc (mmol / 10e9 cells / h)",
    ),
)
fig_3d_Y_lac_glc.show()

fig_3d_Y_gln_glc = go.Figure(
    data=[
        go.Surface(
            x=X_glc,
            y=Y_gln,
            z=Z_delta_Y_cat_Gln_Glc,
            colorscale="Plasma",
            colorbar=dict(title="delta_Y_cat_Gln_Glc"),
        )
    ]
)
fig_3d_Y_gln_glc.update_layout(
    title=f"3D surface: delta_Y_cat_Gln_Glc at constant mu= {mu_fixed} 1/h",
    scene=dict(
        xaxis_title="C_Glc (mmol/L)",
        yaxis_title="C_Gln (mmol/L)",
        zaxis_title="delta_Y_cat_Gln_Glc (mmol / 10e9 cells / h)",
    ),
)
fig_3d_Y_gln_glc.show()

In [16]:
C_Glc_raw = np.asarray(batch.y_points[1], dtype=float)
q_data_raw = {
    "mu": np.asarray(batch.mu_list, dtype=float),
    "q_Glc": np.asarray(batch.q_Glc_list, dtype=float),
    "q_Gln": np.asarray(batch.q_Gln_list, dtype=float),
    "q_Lac": np.asarray(batch.q_Lac_list, dtype=float),
    "q_O2": np.asarray(batch.q_O2_list, dtype=float),
    "q_CO2": np.asarray(batch.q_CO2_list, dtype=float),
}

yield_labels = ["Y_Glc/X", "Y_Lac/Glc", "Y_Gln/Glc", "Y_O2/Glc", "Y_CO2/Glc", "Y_AA/Glc", "Y_Amm/Gln"]
yield_data_raw = {
    "Y_Glc/X": np.asarray(batch.Y_Glc_X_list, dtype=float),
    "Y_Lac/Glc": np.asarray(batch.Y_Lac_Glc_list, dtype=float),
    "Y_Gln/Glc": np.asarray(batch.Y_Gln_Glc_list, dtype=float),
    "Y_O2/Glc": np.asarray(batch.Y_O2_Glc_list, dtype=float),
    "Y_CO2/Glc": np.asarray(batch.Y_CO2_Glc_list, dtype=float),
    "Y_AA/Glc": np.asarray(batch.Y_AA_Glc_list, dtype=float),
    "Y_Amm/Gln": np.asarray(batch.Y_Amm_Gln_list, dtype=float),
}

valid = np.isfinite(C_Glc_raw)
for arr in q_data_raw.values():
    valid &= np.isfinite(arr)
for arr in yield_data_raw.values():
    valid &= np.isfinite(arr)

C_Glc_valid = C_Glc_raw[valid]
order = np.argsort(C_Glc_valid)
C_Glc_grid = C_Glc_valid[order]

q_data = {k: v[valid][order] for k, v in q_data_raw.items()}
df_yields = pd.DataFrame({k: v[valid][order] for k, v in yield_data_raw.items()}, index=C_Glc_grid)
df_yields.index.name = "C_Glc"

display(df_yields.head())

,Y_Glc/X,Y_Lac/Glc,Y_Gln/Glc,Y_O2/Glc,Y_CO2/Glc,Y_AA/Glc,Y_Amm/Gln
C_Glc,,,,,,,
0.001000,3.303108,0.032310,5.453374,28.706883,31.440501,0.011974,1.456092
0.001337,3.641741,0.035623,6.012451,31.649902,34.663770,0.013201,1.605370
0.002247,4.530148,0.044313,7.479196,39.370932,43.120036,0.016422,1.997001
0.007455,1.655272,0.113361,6.079924,32.602183,35.668161,0.044943,1.989905
0.013659,1.077848,0.163144,5.045106,27.572550,30.135056,0.069019,1.981317


In [17]:
fig_nf = plot_simulated_NFs(sim, batch_number=1)
fig_nf.update_layout(title_text="EXCESS_COUPLED: Nutrient factors over batch time")
fig_nf.show()

fig_if = plot_simulated_IFs(sim, batch_number=1)
fig_if.update_layout(title_text="EXCESS_COUPLED: Inhibition factors over batch time")
fig_if.show()

fig_rates = plot_kinetic_rates(sim, batch_number=1)
fig_rates.update_layout(title_text="EXCESS_COUPLED: Kinetic parameters over batch time")
fig_rates.show()

fig_stoich = plot_stoichiometric_yields(sim, batch_number=1)
fig_stoich.update_layout(title_text="EXCESS_COUPLED: Stoichiometric yields over batch time")
fig_stoich.show()

# Optional consolidated kinetics dashboard
fig_all = plot_kinetics(sim, batch_number=1)
fig_all.update_layout(title_text="EXCESS_COUPLED: Complete kinetics overview")
fig_all.show()

In [18]:
sim.data.plot_biomass_metabolites()